---
title: "Análisis Exploratorio de Datos: Ruta Cra 54"
---

In [10]:
import pandas as pd
import numpy as np
from pathlib import Path
import sys

PROJECT_ROOT = Path.cwd().parent

SRC_PATH = PROJECT_ROOT / "src"
DATA_RAW = PROJECT_ROOT /"data"  /"raw"
DATA_PROCESSED = PROJECT_ROOT / "data" /"processed"

if str(SRC_PATH) not in sys.path:
    sys.path.append(str(SRC_PATH))

from utils import eda_toolkit as toolkit

df = pd.read_parquet(DATA_RAW / "timbradas_anio_k54.parquet")
df = df.drop(columns=["id_ruta", "nombre_ruta"])

df_prog = pd.read_parquet(DATA_RAW / "progvehiculos_k54.parquet")

df = df[df["ano"].isin([2023, 2024, 2025])].copy()

df["fecha_inicio"] = pd.to_datetime(df["fecha_inicio"]).dt.date
df["fecha_fin"] = pd.to_datetime(df["fecha_fin"]).dt.date

df["id_estacionalidad_anio"] = df["id_estacionalidad_anio"].astype("int16")
df["promedio_subidas"]       = df["promedio_subidas"].astype("float32")
df["promedio_bajadas"]       = df["promedio_bajadas"].astype("float32")

:::{admonition} Resumen del análisis exploratorio
:class: info

- La serie tiene estructura multi-escala: ciclo semi-diurno (32-33 rezagos), diario (65) y semanal (455). El ciclo semanal es independiente del diario.
- La demanda muestra un perfil bimodal intradía con pico en la mañana, valle al mediodía y segundo pico en la tarde, estable entre semanas y meses.
- Existe una reducción sistemática de la demanda entre años, visible en la comparación mes a mes. Los lags recientes absorben el drift sin necesidad de features de tendencia explícitas.
- Los tipos de estacionalidad modulan la demanda de forma diferenciada: días corrientes y Fiestas Atlánticas sostienen niveles altos, mientras que Temporada y Festivo Nacional reducen la demanda. La codificación debe preservar esa jerarquía.
- La demanda registrada no equivale a la demanda potencial: un cero puede reflejar ausencia de despacho, no de demanda. Esto condiciona la interpretación del modelo y las alertas.
:::

## Introducción

La demanda de pasajeros en sistemas de transporte masivo urbano es una variable operativa crítica, sensible a patrones horarios, calendarios laborales, eventos estacionales y shocks exógenos. El modelado de la demanda en sistemas tipo BRT evoluciona hacia arquitecturas híbridas que integran series temporales agregadas con información contextual, y que se traducen operativamente en decisiones de frecuencia de despacho, dimensionamiento de flota y asignación de capacidad por ruta.

La serie analizada proviene de los registros de demanda y de flota asociados a la ruta CRA 54 (K54) operada por SOBUSA en el Sistema de Transporte Masivo de Barranquilla. Los registros consolidados (`timbradas_anio`) contienen las dimensiones temporales y estacionales, junto con las métricas operativas agregadas. Los registros de flota (`progvehiculos`) contienen la información individual de cada despacho.

:::{admonition} Información: Dataset de Demanda y Flota — Ruta K54
:class: info

Los registros consolidados (`timbradas_anio`) comprenden 11,663 observaciones para la ruta K54, con estructura de franjas horarias de 15 minutos entre 00:00 y 23:45. Contienen las dimensiones temporales (año, día de la semana, franja horaria) y estacionales (tipo de estacionalidad, nombre de evento), junto con las métricas operativas agregadas (`subidas`, `bajadas`, `nro_viajes`, `promedio_subidas`, `promedio_bajadas`).

Los registros de flota (`progvehiculos`) contienen la información individual de cada despacho: fecha-hora de inicio y fin, vehículo, conductor, pasajeros transportados, cancelaciones y estado operativo.

El período analizado (2023–2025) abarca múltiples regímenes operativos. Estos incluyen la operación regular de días corrientes, los festivos nacionales, las temporadas estacionales (Semana Santa, Carnaval de Barranquilla, Fiestas Patronales) y los ciclos anuales diferenciados.
:::

La ruta K54 recorre el corredor norte-sur del Área Metropolitana de Barranquilla, desde el terminal de integración en el municipio de Soledad hasta el municipio de Puerto Colombia, atravesando la zona centro-oriental de Barranquilla. El trazado tiene una longitud total de 56.4 km y se compone de 123 segmentos operativos, con un recorrido de ida y vuelta que comparte parcialmente corredores viales en los tramos centrales. La ruta conecta zonas residenciales de alta densidad en Soledad y el sur de Barranquilla con los polos de actividad económica del centro y el norte de la ciudad, y con el corredor turístico de Puerto Colombia. El sentido de operación y el punto de retorno se ilustran en el mapa presentado a continuación.

In [2]:
_, _ = toolkit.generate_map("k54")

Esta libreta documenta el Análisis Exploratorio de Datos (EDA) de esta ruta: evaluación de la integridad de la base de datos, detección de registros faltantes, discontinuidades en el calendario operativo, análisis de consistencia entre los registros consolidados y los registros de flota, y tratamiento de anomalías. También documenta el análisis de estacionalidad horaria, semanal y anual.

## Análisis preliminar

### Registros consolidados

El conjunto de datos estuvo compuesto por 11,663 registros consolidados (`timbradas_anio`) correspondientes a la operación de la ruta CRA 54, abarcando un rango temporal de 2023 a 2026. Se cuenta con 17 variables que combinan dimensiones temporales, dimensiones estacionales y métricas operativas agregadas, almacenadas en tipos enteros de distinta precisión, tipos temporales y cadenas de texto.

Por instrucción de la empresa, el análisis se limitó al final de 2025, quedando excluido el año 2026. Tras este filtro, el conjunto de datos quedó compuesto por 8,808 registros consolidados. Las variables se almacenaron en tipos enteros de distinta precisión (`int8`, `int16`, `int32`), tipos temporales (`time`, `date`), cadenas de texto y valores de precisión simple (`float32`). Las métricas operativas (`subidas`, `bajadas`, `nro_viajes`) se almacenaron en formato entero, mientras que los promedios por viaje se almacenaron en precisión simple. No se observaron datos faltantes en ninguna de las variables analizadas.

In [11]:
_ = toolkit.dataframe_integrity_blocks(df, n_blocks=3)

Variable,Data type,Variable,Data type,Variable,Data type
ano,int16,minuto_num,int8,subidas,int32
id_dia_semana,int8,tipo_estacionalidad,str,bajadas,int32
id_estacionalidad_anio,int16,nombre_evento,str,nro_viajes,int32
hora_inicio,time,fecha_inicio,date,promedio_subidas,float32
hora_fin,time,fecha_fin,date,promedio_bajadas,float32
hora_num,int8,duracion_evento_dias,int16,,


La tabla consolidada (`timbradas_anio`) presenta observaciones agregadas por patrón operativo. Cada fila combina un año, un día de la semana, una estacionalidad y una franja horaria de 15 minutos, y sintetiza en una única entrada las métricas operativas acumuladas sobre todos los días del período que comparten ese patrón. Para estacionalidades de duración 1 (festivos individuales) el agregado corresponde a un único día; para estacionalidades de duración larga, como "Días corrientes", el agregado suma sobre los múltiples días de la semana que caen dentro del rango anual.

In [12]:
_ = toolkit.dataframe_head_table(df, n=5)

ano,id_dia_semana,id_estacionalidad_anio,hora_inicio,hora_fin,hora_num,minuto_num,tipo_estacionalidad,nombre_evento,fecha_inicio,fecha_fin,duracion_evento_dias,subidas,bajadas,nro_viajes,promedio_subidas,promedio_bajadas
2023,1,121,01:00:00,01:15:00,1,0,FESTIVO_NACIONAL,Día de los Reyes Magos,2023-01-09,2023-01-09,1,69,67,1,69.000000,67.000000
2023,1,121,06:30:00,06:45:00,6,30,FESTIVO_NACIONAL,Día de los Reyes Magos,2023-01-09,2023-01-09,1,0,0,1,0.000000,0.000000
2023,1,121,07:30:00,07:45:00,7,30,FESTIVO_NACIONAL,Día de los Reyes Magos,2023-01-09,2023-01-09,1,123,148,1,123.000000,148.000000
2023,1,121,07:45:00,08:00:00,7,45,FESTIVO_NACIONAL,Día de los Reyes Magos,2023-01-09,2023-01-09,1,256,262,4,64.000000,65.500000
2023,1,121,08:00:00,08:15:00,8,0,FESTIVO_NACIONAL,Día de los Reyes Magos,2023-01-09,2023-01-09,1,184,179,3,61.330002,59.669998


La verificación empírica reveló que el nivel de agregación resulta insuficiente. Al comparar los totales del patrón "lunes, Días corrientes 2023" contra los despachos individuales de progvehiculos, se confirmó que la tabla no representa días particulares, sino sumas acumuladas sobre el conjunto de días del patrón. Además, el ratio entre ambas fuentes varió entre 0.025 y 96.8 según la hora, cuando debería ser constante. Esta inconsistencia invalida la tabla como fuente para series diarias confiables.

Dado que el reto requiere pronosticar demanda por rango horario y recomendar frecuencias de despacho, se adopta progvehiculos como fuente primaria. Esta tabla contiene los despachos individuales con fecha y hora reales, lo que permite reconstruir la demanda a la granularidad requerida y construir las variables analíticas necesarias para el modelado predictivo.

### Registros de flota

El conjunto de datos de flota (`progvehiculos`) estuvo compuesto por 298,778 registros individuales de despacho correspondientes a la operación de la ruta K54, abarcando un rango temporal de 2023 a 2026. Se cuenta con 74 variables que describen cada viaje en detalle, almacenadas en tipos enteros, temporales, categóricos y de texto. La clasificación operativa de los registros según su estado de finalización revela una proporción mayoritaria de viajes completados, seguida de viajes cancelados y un número marginal de viajes incompletos. Los viajes cancelados, aunque interrumpidos, registraron un promedio de 74 pasajeros por viaje, lo que indica que la operación se ejecutó parcialmente antes de la cancelación. Esta evidencia sugiere que la cancelación no implica ausencia de demanda, sino una interrupción del servicio durante el recorrido, y por lo tanto estos registros se conservan en el análisis por representar abordajes efectivos.

In [84]:
_, _, _ = toolkit.plot_trip_status(
    df_prog, title="Estado de los viajes — K54 (2023–2025)", y_label_pad=10,
    status_labels=("Completado", "Incompleto", "Cancelado")
)

No obstante, la mayoría de estas variables describen eventos que ocurren durante o después del viaje, por lo que no pueden emplearse como predictores sin incurrir en fuga de información. Las métricas operativas, los atributos de resultado, las variables de recaudo y los campos de auditoría reflejan el resultado de la operación, no las condiciones previas al despacho. Por este motivo, el conjunto se redujo a siete variables que describen cada viaje desde su condición previa. Las dos columnas de estado (`finalizado` y `cancelada`) se consolidaron en un único indicador binario, `es_cancelado`, que preserva la información operativa sin redundancia y permite distinguir directamente los viajes completados de los cancelados.

In [13]:
cols_finales = [
    "numeropasajeros",
    "fechainicio",
    "fechasalida",
    "fechafin",
    "finalizado",
    "cancelada",
    "idprogramacion",
    "idvehiculo",
]

df_prog = df_prog[[c for c in cols_finales if c in df_prog.columns]].copy()

df_prog["fechainicio"] = pd.to_datetime(df_prog["fechainicio"])
df_prog["fechasalida"] = pd.to_datetime(df_prog["fechasalida"])
df_prog["fechafin"]    = pd.to_datetime(df_prog["fechafin"])

df_prog = df_prog[
    (df_prog["fechainicio"].dt.year.isin([2023, 2024, 2025])) &
    ~((df_prog["finalizado"] != "S") & (df_prog["cancelada"] != "S"))
].copy()

df_prog["es_cancelado"] = (df_prog["cancelada"] == "S").astype("int8")
df_prog = df_prog.drop(columns=["finalizado", "cancelada"])

_ = toolkit.dataframe_integrity_blocks(df_prog, n_blocks=2)

Variable,Data type,Variable,Data type
numeropasajeros,int32,idprogramacion,int64
fechainicio,Timestamp,idvehiculo,str
fechasalida,Timestamp,es_cancelado,int8
fechafin,Timestamp,,


La tabla resultante está organizada con un registro por viaje. Cada fila representa un despacho individual de la ruta K54, correspondiente a un recorrido completo de ida y vuelta, y los valores de conteo de pasajeros se registran como totales acumulados durante todo el recorrido, no desagregados por franja horaria ni por punto del trayecto. Es decir, la tabla permite reconstruir cuántos viajes ocurrieron en un intervalo dado y cuántos pasajeros transportó cada uno, pero no contiene información sobre la distribución temporal interna del recorrido: no se sabe en qué momento del viaje subieron o bajaron los pasajeros, solo el total al cierre del despacho.

In [14]:
_ = toolkit.dataframe_head_table(df_prog, n=5)

numeropasajeros,fechainicio,fechasalida,fechafin,idprogramacion,idvehiculo,es_cancelado
136,2023-01-01 04:46:26,2023-01-01 05:00:00,2023-01-01 07:25:11,5061766,SOBUSA461,0
84,2023-01-01 04:58:31,2023-01-01 05:10:00,2023-01-01 07:37:49,5061767,SOBUSA491,0
72,2023-01-01 05:05:44,2023-01-01 05:20:00,2023-01-01 07:45:09,5061768,SOBUSA457,0
56,2023-01-01 05:23:17,2023-01-01 05:36:00,2023-01-01 08:03:44,5061770,SOBUSA196,0
44,2023-01-01 05:31:46,2023-01-01 05:28:00,NaT,5061769,SOBUSA420,1


:::{admonition} Información: Fuentes con granularidad temporal
:class: info

Existen dos tablas complementarias que contienen desagregación temporal o espacial de los abordajes, pero con limitaciones que impiden su uso como fuente principal del modelo.

La tabla `conteo_pasajeros_destino` registra cada evento individual de subida y bajada con marca temporal completa y coordenadas GPS del vehículo al momento del evento. Sin embargo, su volumen supera los 41 GB en la instancia asignada, y el campo idpunto (identificador de parada) aparece nulo en la mayoría de los registros, lo que impide reconstruir la demanda por parada de forma consistente.

La tabla `timbradas_segmentos` descompone cada viaje en segmentos operativos y registra subidas, bajadas y pasajeros por segmento. No obstante, su cobertura en la instancia asignada se limita a enero y febrero de 2023, sin datos para el resto del período analizado.
:::

A diferencia de la tabla consolidada (`timbradas_anio`), que no presenta valores faltantes, la tabla de flota contiene dos variables con datos ausentes: `fechafin` con 16,089 registros nulos (5.39%) y `numeropasajeros` con 2,772 (0.93%). El resto de las variables se encuentra completamente poblado.

El análisis de los 2,772 registros con conteo de pasajeros nulo no mostró asociación con vehículos, años u horas específicas: se distribuyen entre 153 de los 302 vehículos de la flota, con proporción estable entre 2023 y 2025 (0.73% a 1.19%), y se concentran en las horas de mayor operación. Su duración mediana (172 min) es menor que la de los viajes válidos (225 min), lo que sugiere cierres prematuros del registro más que fallos de operación. El impacto en la demanda total es de 0.91%. Aunque una recuperación de estos datos podría ser posible mediante un análisis conjunto con el área técnica de la empresa, dicha recuperación no se justifica para los objetivos del presente análisis dada su baja proporción. En consecuencia, estos registros se excluyeron.

In [15]:
nulos = (
    df_prog
    .isna()
    .sum()
    .to_frame(name="n_nulos")
)

nulos["pct_nulos"] = (nulos["n_nulos"] / len(df_prog) * 100).round(2)
nulos["n_validos"] = len(df_prog) - nulos["n_nulos"]
nulos = nulos.sort_values("pct_nulos", ascending=False)

_ = toolkit.dataframe_head_table(nulos.reset_index().rename(columns={"index": "variable"}),
                         n=len(nulos))

variable,n_nulos,pct_nulos,n_validos
fechafin,16089,5.390000,282685
numeropasajeros,2772,0.930000,296002
fechainicio,0,0.000000,298774
fechasalida,0,0.000000,298774
idprogramacion,0,0.000000,298774
idvehiculo,0,0.000000,298774
es_cancelado,0,0.000000,298774


Tras excluir los registros sin conteo de pasajeros, el dataset conserva 15,853 viajes con fechafin nulo, todos correspondientes a viajes cancelados. Estos registros mantienen su conteo de demanda y se preservan para el análisis, ya que la duración del recorrido no resulta indispensable para el modelado por franja.

El chequeo de consistencia temporal identificó 70 viajes con marcas de tiempo internamente incoherentes, incluyendo casos donde `fechafin` es anterior a `fechasalida` y otros donde ambos valores coinciden, lo que produce duraciones nulas o negativas imposibles en la operación real. Estos registros se concentran casi en su totalidad en 2024 (64 casos), con presencia marginal en 2023 (2) y 2025 (4), y se atribuyen a errores del sistema de cierre. Dado su carácter inconsistente y su baja proporción (0.024% del dataset), se excluyeron del análisis.

In [16]:
df_prog_check = df_prog.loc[
    df_prog["numeropasajeros"].notna() & (df_prog["es_cancelado"] == 0)
].copy()

df_prog_check["duracion_min"] = (
    (df_prog_check["fechafin"] - df_prog_check["fechasalida"])
    .dt.total_seconds() / 60
).round(1)

df_incons = df_prog_check[df_prog_check["duracion_min"] <= 0].copy()

cols = ["numeropasajeros", "fechainicio", "fechafin", "duracion_min",
        "idprogramacion", "idvehiculo"]

top_incons = (
    df_incons[cols]
    .sort_values("duracion_min")
    .head(10)
    .reset_index(drop=True)
)

styled = (
    top_incons.style
    .hide(axis="index")
    .set_table_styles(toolkit._table_style_rules())
    .format({"duracion_min": "{:.1f}"})
)

toolkit._render_styled(styled)

numeropasajeros,fechainicio,fechafin,duracion_min,idprogramacion,idvehiculo
17,2024-03-20 09:33:20,2023-12-15 10:36:26,-138191.6,6078086,SOBUSA470
95,2024-09-05 11:59:13,2024-08-10 11:09:19,-37490.7,6464192,SOBUSA159
34,2023-12-18 13:41:05,2023-12-15 10:36:26,-4508.6,5863926,SOBUSA167
29,2023-05-05 13:21:06,2023-05-02 12:46:34,-4359.4,5335112,SOBUSA194
0,2024-11-27 05:15:50,2024-11-26 23:23:39,-363.4,6645395,SOBUSA458
34,2024-12-02 05:45:54,2024-12-02 00:44:57,-309.0,6656963,SOBUSA151
0,2024-11-27 05:25:46,2024-11-27 00:55:59,-282.0,6645284,SOBUSA426
10,2024-12-02 06:01:09,2024-12-02 01:39:33,-273.4,6656865,SOBUSA19
0,2024-11-27 06:14:17,2024-11-27 02:08:03,-253.0,6645599,SOBUSA179
56,2024-11-13 08:04:59,2024-11-13 04:23:57,-232.0,6613808,SOBUSA154


Una vez depurados los registros faltantes y las inconsistencias temporales, se incorporó la variable `duracion_min` al dataset, calculada como la diferencia en minutos entre `fechasalida` y `fechafin`. Esta variable se conserva en `df_prog` porque permite verificar la consistencia operativa de los viajes y servirá como referencia para los análisis posteriores de calidad y de modelado.

In [17]:
df_prog["duracion_min"] = (
    (df_prog["fechafin"] - df_prog["fechasalida"])
    .dt.total_seconds() / 60
)

df_prog = df_prog[df_prog["numeropasajeros"].notna()].copy()

mask_cancelled = df_prog["es_cancelado"] == 1
mask_inconsistent = (df_prog["duracion_min"] <= 0) & (~mask_cancelled)

n_before = len(df_prog)
n_dropped = mask_inconsistent.sum()
n_dropped_pax = (
    mask_inconsistent & (df_prog["numeropasajeros"] > 0)
).sum()

df_prog = df_prog[~mask_inconsistent].copy()

La fase de análisis preliminar concluye con la definición del enfoque de modelado. El reto exige predecir la demanda por ruta y franja horaria, y traducir esa predicción en recomendaciones de frecuencia de despacho para horizontes de 30, 60 y 120 minutos.

La decisión operativa que el sistema debe soportar es concreta: cuántos buses enviar en cada ventana de despacho. Esto define la unidad natural del problema. No interesa estimar cuánta demanda existe en un instante dado, sino cuánta demanda absorberá el conjunto de vehículos que se despachen en una franja específica. Cada viaje es, entonces, la unidad de información del modelo: dada su hora de salida y su contexto operativo, permite estimar los pasajeros que el bus recogerá durante su recorrido.

Bajo esta formulación, el total de abordajes de cada viaje se suma con el de los demás viajes despachados en la misma franja de 15 minutos, produciendo una serie temporal de demanda agregada por franja. Esa serie es la que alimenta el optimizador de frecuencias, que traduce la estimación en headway, buses por hora y vehículos requeridos. La desagregación temporal de los abordajes dentro del recorrido pierde relevancia operativa bajo este esquema, porque las decisiones se toman sobre la franja de salida y no sobre el momento exacto en que ocurren las subidas a lo largo del trayecto.

## Análisis de valores atípicos

Antes de agregar los viajes por franja horaria es indispensable determinar qué registros son válidos. La tabla de flota contiene 298,774 viajes, y no todos corresponden a operaciones reales: algunos tienen valores incompatibles con la capacidad de un bus, otros presentan duraciones que exceden el ciclo normal de la ruta, y otros muestran tasas de recogida atípicas. Incluirlos distorsionaría las estimaciones de demanda y las recomendaciones de frecuencia.

El análisis de calidad usa dos criterios operativos: el número de pasajeros por viaje, acotado por la capacidad máxima de un bus articulado, y la duración del recorrido, acotada por el ciclo completo de la ruta. Ambos permiten descartar valores imposibles sin depender de supuestos distribucionales.

:::{admonition} Información: Filtro Hampel
:class: info

El filtro Hampel detecta valores atípicos usando estadística robusta. Para cada observación $x_i$ se considera una ventana centrada de $2k + 1$ vecinos y se calculan dos estadísticos locales:

$$
m_i = \text{mediana}\left( x_j \right), \quad \text{y} \quad \text{MAD}_i = \text{mediana}\left(\left| x_j - m_i \right| \right), \quad j \in [i-k, i+k]
$$

donde $m_i$ es la mediana local y $\text{MAD}_i$ la desviación absoluta mediana respecto a ella. Una observación se marca como atípica cuando su desviación excede un múltiplo del MAD:

$$
\frac{|x_i - m_i|}{1.4826 \cdot \text{MAD}_i} > t
$$

El factor $1.4826$ escala la MAD para que sea consistente con la desviación estándar bajo normalidad, y $t$ es el umbral en unidades de desviaciones estándar equivalentes (típicamente entre 3 y 5). La elección de mediana y MAD en lugar de media y desviación estándar es lo que da robustez al método: ambas son resistentes a outliers, mientras que los momentos clásicos se ven distorsionados por ellos.
:::

El análisis de calibración mostró que la curva de observaciones retenidas se aplana a partir de 4.5 MADs: por encima de ese punto cada incremento del umbral recupera menos de 800 casos. Se adoptó un umbral de 5.0 MADs por ser un estándar consolidado en detección de outliers y marcar únicamente el 0.55% del dataset (1,628 observaciones). Este valor se sitúa en la zona de rendimientos decrecientes de la curva, lo que indica que umbrales más altos no aportan ganancias significativas de cobertura.

In [31]:
_, _, resumen = toolkit.calibrate_hampel_threshold(
    df_prog, col="numeropasajeros",
    col_order="fechainicio",
    t_values=(3.0, 3.5, 4.0, 4.5, 5.0, 5.5, 6.0, 6.5, 7.0),
    k=7, title="Calibración Hampel sobre número de pasajeros", x_label_pad=12, y_label_pad=18,
    xlab="Umbral $t$ (MADs)"
)

El filtro Hampel aplicado únicamente sobre el conteo de pasajeros no permite confirmar por sí solo la existencia de un error: un valor alto puede corresponder a un bus lleno en hora pico y uno bajo a un viaje legítimo en hora valle. Para robustecer la detección se derivó la duración del viaje a partir de las marcas temporales de inicio y fin de cada despacho, y se aplicó el mismo filtro sobre esa nueva variable. Los viajes cancelados, que no registran hora de finalización, se excluyeron de esta calibración por carecer de la información necesaria.

In [33]:
resumen_mostrar = resumen[["t", "n_retained", "n_flagged"]].copy()
resumen_mostrar = resumen_mostrar.rename(columns={
    "t": "umbral t",
    "n_retained": "n_retenidos",
    "n_flagged": "n_marcados",
})
resumen_mostrar["umbral t"] = resumen_mostrar["umbral t"].map(lambda x: f"{x:.1f}")
resumen_mostrar["delta_retenidos"] = resumen_mostrar["n_retenidos"].diff()
resumen_mostrar["delta_retenidos"] = resumen_mostrar["delta_retenidos"].fillna(0).astype(int)

_ = toolkit.dataframe_head_table(resumen_mostrar, n=len(resumen_mostrar))

umbral t,n_retenidos,n_marcados,delta_retenidos
3.0,286356,8841,0
3.5,289644,5553,3288
4.0,291640,3557,1996
4.5,292912,2285,1272
5.0,293661,1536,749
5.5,294169,1028,508
6.0,294455,742,286
6.5,294663,534,208
7.0,294783,414,120


A diferencia del conteo de pasajeros, la duración del viaje no presenta un codo claro en la curva de calibración, dado que su variabilidad natural es mayor y no existe un umbral donde los valores legítimos terminen abruptamente. Se adoptó el mismo umbral de 5.0 MADs utilizado para el filtro anterior, con el fin de mantener coherencia metodológica y evitar la introducción de un criterio ad hoc.

In [70]:
df_prog_dur = df_prog.copy()
df_prog_dur["duracion_min"] = (
    (df_prog_dur["fechafin"] - df_prog_dur["fechainicio"]) # CORREGIR
    .dt.total_seconds() / 60
)

df_prog_dur = df_prog_dur[df_prog_dur["duracion_min"].notna()].copy()

_, _, resumen_dur = toolkit.calibrate_hampel_threshold(
    df_prog_dur, col="duracion_min", col_order="fechainicio",
    t_values=(3.0, 3.5, 4.0, 4.5, 5.0, 5.5, 6.0, 6.5, 7.0),
    k=7, title="Calibración Hampel sobre duración del viaje",
    ylab="Observaciones retenidas", x_label_pad=12, y_label_pad=18,
    xlab="Umbral $t$ (MADs)"
)


La asociación entre ambos criterios fue estadísticamente significativa ($\chi^2$ = 5,572.50, $p$ < 0.001), aunque el tamaño del efecto medido por $V$ de Cramér fue pequeño ($V$ = 0.137). El odds ratio de 16.34 indica que un viaje marcado por duración anómala tiene esa probabilidad multiplicada de presentar también conteo anómalo. Sin embargo, la magnitud global de la asociación es modesta: solo el 4.8% de los viajes marcados por duración presentan también conteo anómalo, lo que confirma que los filtros capturan fenómenos parcialmente superpuestos pero no redundantes. La aplicación conjunta de ambos criterios se justifica tanto por su significancia estadística como por su capacidad de detectar casos que cada uno individualmente no capturaría.

In [71]:
resumen_dur_mostrar = resumen_dur[["t", "n_retained", "n_flagged"]].copy()
resumen_dur_mostrar = resumen_dur_mostrar.rename(columns={
    "t": "umbral t",
    "n_retained": "n_retenidos",
    "n_flagged": "n_marcados",
})
resumen_dur_mostrar["umbral t"] = resumen_dur_mostrar["umbral t"].map(lambda x: f"{x:.1f}")
resumen_dur_mostrar["delta_retenidos"] = (
    resumen_dur_mostrar["n_retenidos"].diff().fillna(0).astype(int)
)

_ = toolkit.dataframe_head_table(resumen_dur_mostrar, n=len(resumen_dur_mostrar))

umbral t,n_retenidos,n_marcados,delta_retenidos
3.0,257049,22295,0
3.5,259521,19823,2472
4.0,261290,18054,1769
4.5,262637,16707,1347
5.0,263716,15628,1079
5.5,264583,14761,867
6.0,265256,14088,673
6.5,265918,13426,662
7.0,266494,12850,576


La inspección del diagrama de cajas de la duración revela que la mayoría de los viajes se concentra entre 180 y 250 minutos, con una mediana cercana a 225. Dado que la ruta K54 recorre 56.4 km y un bus de servicio público opera con paradas programadas, la velocidad comercial típica oscila entre 15 y 25 km/h. Un viaje completado en menos de 30 minutos implicaría una rapidez promedio superior a 110 km/h, físicamente imposible para un bus urbano en operación comercial.

In [89]:
_, _, _ = toolkit.plot_hampel_boxplots(
    df_prog,
    t=(5.0, 5.0),
    titles=("Número de pasajeros", "Duración (min)"),
    ylim_passengers=(-49, 400),
    ylim_duration=(-49, 600),
)

### Duración de los viajes

El análisis por umbrales de duración identifica 5,597 viajes (1.90%) con duración inferior a 90 minutos, incompatibles con operación con paradas (>38 km/h implícitos). El 59.57% se concentra en la hora 5 (12.28% de esa franja, frente a ~1% del resto del día), coincidiendo con el arranque de jornada (ventana operativa 4:30–20:30). El análisis de `fechafin` descarta generación programática por cierre del sistema (minutos y segundos uniformemente distribuidos, idénticos al patrón de viajes largos). La causa exacta no puede determinarse con los datos disponibles; el patrón es consistente con movimientos de posicionamiento al inicio de la jornada.

In [18]:
df_temp = df_prog.copy()
df_temp["hora"] = df_temp["fechasalida"].dt.hour

fig, ax, tabla = toolkit.plot_short_trips_by_hour(
    df_temp, threshold_min=90,
    title="Viajes con duración inferior a 90 min por hora",
    ylab="Tasa dentro de la hora (%)", xlab = "Hora del día"
)

El sistema conserva 123 registros con `fechainicio` entre las 21:00 y las 23:00, pero ninguno corresponde a una salida física en esa franja: sus `fechasalida` se ubican entre las 16:00 y las 20:44, dentro de la ventana operativa de la ruta (04:30–20:38). Son producto de sincronización diferida del dispositivo a bordo, que acumula registros sin conexión y los descarga al regresar al patio, sellando la marca de inicio con 2 a 4 horas de retraso. No corresponden, por tanto, a operación nocturna.

Bajo la convención de hora de salida física, la ruta no registra operación comercial después de las 20:38. El conteo por `fechainicio` muestra 379, 1 y 2 pasajeros en las horas 21, 22 y 23, pero son artefactos del sello tardío del sistema: los 379 ya están contados en su franja real de salida, y los 3 restantes desaparecen al usar `fechasalida` como referencia horaria.

In [19]:
_, _, _ = toolkit.plot_passengers_by_hour(
    df_prog, col_start="fechainicio",
    hours=(21, 22, 23),
    title="Pasajeros totales en horas 21-23",
    xlab="Hora del día (fecha de inicio)",
    ylab="Pasajeros totales"
)

La inspección de la hora 21 reveló una diferencia importante respecto a las horas 22 y 23. De los 72 viajes con duración válida registrados en esa franja, cinco presentan perfil comercial normal: duraciones entre 152 y 179 minutos, entre 19 y 51 pasajeros, y salida física entre las 20:40 y las 20:44. Corresponden a los últimos despachos de la jornada, cuyo `fechainicio` fue sellado por el sistema entre 15 y 30 minutos después de la salida real, consistente con el patrón de sincronización diferida documentado. El vehículo `SOBUSA302` aparece en tres de estos casos y las fechas son dispersas a lo largo del período analizado (2023 a 2025).

Los 67 registros restantes son anómalos. La mayoría presentan duraciones inferiores a 10 minutos, correspondientes a cierres inmediatos del sistema, y un grupo menor supera los 400 minutos, con registros que permanecieron abiertos durante toda la noche hasta 999 minutos (16.6 horas). De los nueve viajes anómalos con pasajeros registrados (entre 1 y 43), ninguno presenta una duración dentro del rango operativo.

In [20]:
_, _, _ = toolkit.plot_hour_plausibility_breakdown(
    df_prog, hour=21,  edge_color="black",
    title="Desglose de la hora 21",
    labels=("Plausible", "Anómalo"),
    ylab="Pasajeros totales", xlab="", 
    avg_label_fmt="{:.2f} pax/viaje"
)

Los cinco casos plausibles se conservan en el análisis. Su `fechasalida` cae entre las 20:40 y las 20:44, dentro de la ventana operativa regular, y sus duraciones (152–179 min) y volúmenes de pasajeros (19–51) son consistentes con el perfil comercial de la ruta. Corresponden a los últimos despachos de la jornada, sellados por el sistema entre 15 y 30 minutos después de la salida física. No requieren confirmación adicional con el área operativa: son operación regular con registro tardío. Los 67 anómalos se excluyen.

In [21]:
## CORREGIR: Colicar Hora salida-------

df_check = df_prog.copy()
df_check["_hora"] = df_check["fechainicio"].dt.hour
df_check["_minuto"] = df_check["fechainicio"].dt.minute

subset = df_check[
    (df_check["_hora"] == 21) &
    (df_check["duracion_min"].notna())
].copy()

# Perfil plausible: duración en rango operativo, ocupación comercial
# clara (>= 19 pasajeros) e inicio en los primeros 10 minutos de la hora.
mask_plausible = (
    subset["duracion_min"].between(135, 250) &
    (subset["numeropasajeros"] >= 19) &
    (subset["_minuto"] <= 10)
)

plausibles = subset[mask_plausible].copy()

dias_es = {
    "Monday": "Lunes",
    "Tuesday": "Martes",
    "Wednesday": "Miércoles",
    "Thursday": "Jueves",
    "Friday": "Viernes",
    "Saturday": "Sábado",
    "Sunday": "Domingo",
}

plausibles["fecha"] = plausibles["fechainicio"].dt.strftime("%Y-%m-%d")
plausibles["dia_semana"] = (
    plausibles["fechainicio"].dt.day_name().map(dias_es)
)
plausibles["hora_inicio"] = plausibles["fechainicio"].dt.strftime("%H:%M:%S")
plausibles["hora_fin"] = plausibles["fechafin"].dt.strftime("%H:%M:%S")

plausibles = plausibles.rename(columns={
    "fecha": "Fecha",
    "dia_semana": "Día de la semana",
    "hora_inicio": "Hora inicio",
    "hora_fin": "Hora fin",
    "duracion_min": "Duración (min)",
    "numeropasajeros": "Pasajeros",
    "idvehiculo": "Vehículo",
    "idprogramacion": "ID programación",
})

cols = ["Fecha", "Día de la semana", "Hora inicio", "Hora fin",
        "Duración (min)", "Pasajeros", "Vehículo", "ID programación"]

tabla_plausibles = (
    plausibles[cols]
    .sort_values("Fecha")
    .reset_index(drop=True)
)

tabla_plausibles["Duración (min)"] = tabla_plausibles["Duración (min)"].round(1)

if len(tabla_plausibles) == 0:
    print("No hay viajes que cumplan el perfil plausible con los filtros actuales.")
else:
    _ = toolkit.dataframe_head_table(
        tabla_plausibles, n=len(tabla_plausibles)
    )

Fecha,Día de la semana,Hora inicio,Hora fin,Duración (min),Pasajeros,Vehículo,ID programación
2023-10-30,Lunes,21:03:00,23:22:53,158.900000,19,SOBUSA116,5750040
2024-04-30,Martes,21:00:21,23:15:54,151.900000,33,SOBUSA417,6175661
2024-12-13,Viernes,21:04:28,23:37:19,173.300000,50,SOBUSA302,6685038
2025-05-23,Viernes,21:10:41,23:38:47,178.800000,39,SOBUSA302,7048754
2025-06-04,Miércoles,21:05:43,23:23:16,159.300000,51,SOBUSA302,7075996


El análisis acumulado de duración para la hora 5 muestra un patrón particular: el 12.28% de los viajes dura menos de 90 minutos, el 21.51% menos de 150, y el 48.52% menos de 180. Casi la mitad de la operación de esa hora se completa con duraciones por debajo del rango operativo estándar del resto del día, lo que motiva una inspección específica.

La inspección individual de estos viajes cortos reveló que no corresponden a errores del sistema. De los 3,334 casos identificados, el 99.9% es seguido por un segundo viaje del mismo vehículo con una mediana de separación de 20.5 minutos (77.9% por debajo de 30 minutos). La duración del corto tiene mediana de 79.3 minutos (IQR 73.9–84.2) y la del siguiente 231.1 minutos. La suma de ambos tiene mediana de 310.0 minutos, superior al ciclo típico del resto del día (221.8 minutos), lo que descarta que sean tramos parciales registrados por separado. El 97.5% ocurre el mismo día.

In [22]:
df_h5 = df_prog.copy()
df_h5["_hora"] = df_h5["fechasalida"].dt.hour

df_h5 = df_h5[
    (df_h5["_hora"] == 5) &
    (df_h5["duracion_min"].notna())
].copy()

_, _, tabla = toolkit.plot_duration_ecdf(
    df_h5,
    thresholds=(20, 30, 60, 90, 120, 150, 180, 200, 220, 300, 400, 500),
    xlim=(0, 400),
    title="Distribución acumulada de la duración — Hora 5",
    xlab="Duración (min)", ylab="Porcentaje acumulado (%)"
)

Del total, 3,148 viajes (94.4%) registran pasajeros con mediana de 40 abordajes (IQR 27–52), consistente con servicio comercial real. Los 186 restantes (5.6%), sin pasajeros y con duración mediana menor (45.7 frente a 79.7 en los que sí cargan), presentan un perfil compatible con movimientos de posicionamiento. Los viajes cortos con pasajeros contribuyen a la serie de demanda por franja porque sus abordajes son efectivos; sin embargo, se excluyen del cálculo de indicadores operativos como el headway o la duración promedio del ciclo, dado que su extensión no representa un recorrido completo de la ruta.

La distribución horaria de los viajes con duración superior a 420 minutos muestra una progresión clara hacia el cierre de jornada: 2.80% a las 15:00, 6.16% a las 16:00, 7.74% y 7.91% en 17 y 18 horas, 8.84% a las 19:00 y 12.61% a las 20:00. En las horas intermedias (6 a 14) la tasa se mantiene por debajo del 1.2%, mientras que las horas de arranque presentan un patrón secundario: 2.54% en la hora 4 y 1.63% en la hora 5, consistente con salidas que el sistema tarda en cerrar.

In [23]:
_, _, tabla = toolkit.plot_long_trips_by_hour(
    df_prog, col_start="fechasalida", threshold_min=420,
    title="Distribución horaria de viajes > 420 min",
    xlab="Hora del día",
    ylab="Porcentaje de viajes largos (%)",
)

A diferencia de los viajes cortos, cuya concentración en la hora 5 fue verificada como operación real con perfil de pasajeros y secuencia operativa compatibles, los largos no presentan evidencia de servicio comercial: sus duraciones superan cualquier ciclo razonable de la ruta (más de 7 horas por viaje). En consecuencia, la decisión sobre su inclusión se traslada al análisis distribucional de pasajeros, donde se evalúa si su perfil de demanda es compatible con la operación regular de la ruta.

### Número de pasajeros

El análisis del número de pasajeros por viaje identificó 41 registros que superan el umbral del filtro Hampel (~250 pasajeros). De estos, dos son bugs evidentes del sensor: 97,199 y 28,816 pasajeros, con duraciones imposibles de 6 días y 14 horas respectivamente. Los 39 casos restantes tienen conteos entre 251 y 507 pasajeros, y 17 de ellos corresponden a viajes cancelados sin cierre registrado.

Al revisar las fechas de los 22 casos con duración válida, se detectó que 3 se concentran en la misma jornada (2024-09-06). La comparación con días vecinos confirma que esa fecha presentó un comportamiento anómalo: solo 51 viajes registrados frente a los ~250 habituales, una tasa de cancelación del 35.3% (vs ~6% normal) y un pax máximo de 487 (más del doble del rango típico). Este patrón corresponde a un fallo del sistema de registro, no a operación real. Se excluyen los viajes de esa fecha del análisis, quedando 19 casos para evaluación posterior.

In [24]:
UMBRAL        = 250
UMBRAL_BUG    = 10000
fecha_anomala = pd.Timestamp("2024-09-06").date()

filtro1 = df_prog[df_prog["numeropasajeros"] > UMBRAL].copy()

filtro2 = filtro1[
    (filtro1["numeropasajeros"] < UMBRAL_BUG) &
    (filtro1["fechasalida"].dt.date != fecha_anomala)
].copy()

cols = ["numeropasajeros", "fechasalida", "fechafin", "duracion_min",
        "idprogramacion", "idvehiculo"]

tabla_final = (
    filtro2[cols]
    .sort_values("numeropasajeros", ascending=False)
    .reset_index(drop=True)
    .rename(columns={
        "numeropasajeros": "Pasajeros",
        "fechasalida":     "Fecha salida",
        "fechafin":        "Fecha fin",
        "duracion_min":    "Duración (min)",
        "idprogramacion":  "ID programación",
        "idvehiculo":      "Vehículo",
    })
)

tabla_final["Duración (min)"] = tabla_final["Duración (min)"].round(1)

_ = toolkit.dataframe_head_table(tabla_final, n=10)

df_prog = df_prog[
    (df_prog["numeropasajeros"] < UMBRAL_BUG) &
    (df_prog["fechasalida"].dt.date != fecha_anomala)
].copy()

Pasajeros,Fecha salida,Fecha fin,Duración (min),ID programación,Vehículo
507,2024-10-08 13:08:00,2024-10-08 17:45:31,277.500000,6535573,SOBUSA475
413,2024-11-12 17:33:00,2024-11-12 20:59:20,206.300000,6612771,SOBUSA475
375,2024-10-21 10:58:00,2024-10-21 20:11:17,553.300000,6563160,SOBUSA333
351,2023-07-15 16:42:00,2023-07-15 20:27:31,225.500000,5497571,SOBUSA420
345,2023-08-31 11:51:00,2023-08-31 19:43:09,472.200000,5607081,SOBUSA491
344,2023-07-21 16:39:00,2023-07-21 20:21:45,222.800000,5510880,SOBUSA420
341,2024-11-11 16:25:00,2024-11-11 19:17:25,172.400000,6610507,SOBUSA475
337,2024-07-28 08:10:00,2024-07-28 11:04:22,174.400000,6374033,SOBUSA452
331,2023-06-09 15:06:00,NaT,nan,5416532,SOBUSA162
324,2023-08-31 10:48:00,2023-08-31 18:13:32,445.500000,5606839,SOBUSA239


De los 27 casos con más de 250 pasajeros que quedan tras excluir los bugs del sensor y el día anómalo del 2024-09-06, cinco presentan duraciones superiores a 420 minutos (375, 345, 324, 296 y 267 pasajeros respectivamente), con tasas de recogida entre 0.48 y 0.73 pax/min. Estos casos siguen el patrón de los viajes largos identificado previamente y se excluyen por consistencia con el filtro aplicado a esa categoría. Los 22 casos restantes se conservan: 8 son cancelados con demanda real registrada (pax 251–331), 2 presentan tasas de recogida entre 1.75 y 1.95 pax/min (vehículos SOBUSA475 y SOBUSA452), y 12 tienen duraciones y tasas dentro de rangos operativamente plausibles.

El análisis de viajes sin pasajeros por hora muestra un patrón en forma de U consistente con la operación normal de un sistema de transporte: las tasas son más altas al inicio (6.15% en hora 4, 4.17% en hora 5) y al final de la jornada (2.59% en hora 20), y mínimas durante el valle operativo (0.50% en hora 10, con promedio de 0.83% entre las 10 y las 15 horas). El promedio general de viajes con 0 pax es 1.59%, con un máximo de 6.15% en la hora 4. No se identifican picos anómalos que sugieran fallos del sistema, aunque el arranque de jornada concentra una proporción mayor de viajes sin pasajeros que el cierre.

In [25]:
_, _, tabla = toolkit.plot_zero_passenger_trips_by_hour(
    df_prog, col_start="fechasalida",
    title="Distribución horaria de viajes sin pasajeros", xlab="Hora del día",
    ylab="Porcentaje de viajes (%)"
)

La verificación de consistencia física (duración vs pasajeros) no identificó violaciones: ningún viaje con duración inferior a 90 min supera los 150 pasajeros. Los 27 casos retenidos tienen conteos entre 251 y 507 pasajeros. Cinco de ellos (duración 431–562 min, pax 267–375) son registros no segmentados por fallo del sistema: representan el 11–24% de la demanda de su franja horaria específica, pero solo el 0.01–0.07% de la demanda agregada de esas horas a lo largo del período.

La inspección de jornadas con patrón similar reveló 12 días afectados por el mismo fallo en los tres años del período, sin preferencia por día de la semana ($\chi^2$ = 8.95, $p$ = 0.18). Aplicando el criterio a los 157 largos > 420 min de esas jornadas, se excluyen del dataset: la pérdida agregada es de 11,550 pasajeros (0.07% del total) frente al sesgo localizado de hasta 24% en las franjas afectadas. Las franjas conservan entre 11 y 18 viajes tras la exclusión, y el resto del dataset se mantiene íntegro por su perfil de demanda compatible con operación normal.

In [26]:
dias_fallo = pd.to_datetime([
    "2023-08-31", "2023-10-26", "2024-07-28", "2024-09-03",
    "2024-09-17", "2024-10-12", "2024-10-21", "2024-11-05",
    "2024-11-11", "2025-07-29", "2025-10-03", "2025-12-23",
]).date

n_inicial = len(df_prog)
pax_inicial = int(df_prog["numeropasajeros"].sum())

mask_segmentacion = (
    df_prog["fechasalida"].dt.date.isin(dias_fallo) &
    (df_prog["duracion_min"] > 420)
)

df_prog_clean = df_prog[~mask_segmentacion].copy()

La duración del viaje se incorporó únicamente como variable de validación, no como predictor. En producción, la hora de retorno del bus no se conoce al momento de programar los despachos, por lo que no puede alimentar el modelo. Su uso se limitó a verificar la coherencia física de los registros y a detectar casos anomalos, como los dos bugs de sensor ya identificados. Por esta razón, `duracion_min` se excluye del dataset final destinado al modelado predictivo.

## Agregación de datos

Una vez limpiados los datos según los criterios de calidad descritos, corresponde definir el nivel al que se agregarán los viajes. La Especificación Técnica declara en §9.1 que el problema debe formularse como pronóstico por ruta, sentido, segmento y ventana temporal, y el §6.1 eleva segmento_de_ruta y sus derivados a campos obligatorios. Antes de adoptar ese nivel conviene contrastarlo con lo que efectivamente contiene la base autorizada.

La verificación muestra que el contrato del spec no se sostiene en este ambiente: timbradas_segmentos cubre solo 56 días de 2023, `timbradas_segmentos_anio` y `timbradas_segmentos_consolidado` están vacías, ninguna tabla tiene columna sentido, y en la operación de SOBUSA Barranquilla no hay paraderos fijos —`idpunto` está vacío en los 175 millones eventos de `conteo_pasajeros_destino`, mientras que las coordenadas GPS sí están pobladas. El §12.3, que define el contrato de salida del endpoint de predicción, tampoco incluye `segmentId` ni `sentidoId`. Con ese panorama, la agregación debe fijarse en esta sección considerando únicamente las dimensiones que la base soporta de forma continua.

Para construir la franja se adopta el mismo criterio que de `timbradas_anio`: intervalos de 15 minutos anclados a la hora de salida del bus. Formalmente, sea $v$ un viaje con hora de salida $t_v$ (`fechasalida`) y volumen de pasajeros $p_v$ (`numeropasajeros`). Se define $\tau_v = 60 \cdot h(t_v) + m(t_v)$ como los minutos transcurridos desde la medianoche de $t_v$, donde $h(\cdot)$ y $m(\cdot)$ son la hora y el minuto de $t_v$. La franja a la que pertenece $v$ se define como:

$$
\text{franja}(v) = \left\lfloor \frac{\tau_v}{\Delta} \right\rfloor \cdot \Delta, \qquad \Delta = 15 \text{ min}
$$

El conjunto de viajes de `df_prog_clean` que caen en una franja $f$ es $\mathcal{V}_f = \{v : \text{franja}(v) = f\}$, y la variable agregada por franja se define como:

$$
\text{pasajeros}(f) = \sum_{v \in \mathcal{V}_f} p_v
$$

La decisión de anclar en `fechasalida`, y no en `fechainicio`, responde a que la salida es el evento operativo real de despacho. Los datos de calendario y estacionalidad (`tipo_estacionalidad`, `nombre_evento`) se extraen de `timbradas_anio` mediante join por fecha, aprovechando que esa tabla vincula cada patrón estacional a un rango de fechas real (`fecha_inicio`, `fecha_fin`).

In [4]:
df_work = df_prog_clean.copy()

df_work["franja_ts"] = df_work["fechasalida"].dt.floor("15min")

mask_2045 = (
    (df_work["franja_ts"].dt.hour == 20) &
    (df_work["franja_ts"].dt.minute == 45)
)
df_work.loc[mask_2045, "franja_ts"] = (
    df_work.loc[mask_2045, "franja_ts"] - pd.Timedelta(minutes=15)
)

df_agre = (
    df_work.dropna(subset=["fechasalida"])
           .groupby("franja_ts")
           .agg(
               pasajeros = ("numeropasajeros", "sum"),
               n_viajes  = ("numeropasajeros", "size"),
           )
           .reset_index()
)

dias = pd.date_range(
    df_agre["franja_ts"].min().normalize(),
    df_agre["franja_ts"].max().normalize(),
    freq="D",
)

slots_min = range(4 * 60 + 30, 20 * 60 + 30 + 1, 15)

esperado = pd.DatetimeIndex([
    d + pd.Timedelta(minutes=m)
    for d in dias
    for m in slots_min
])

df_agre = (
    df_agre.set_index("franja_ts")
           .reindex(esperado)
           .rename_axis("franja_ts")
           .reset_index()
)

df_agre["pasajeros"] = df_agre["pasajeros"].fillna(0).astype("int32")
df_agre["n_viajes"]  = df_agre["n_viajes"].fillna(0).astype("int16")

df_agre["anio"]       = df_agre["franja_ts"].dt.year
df_agre["mes"]        = df_agre["franja_ts"].dt.month
df_agre["dia"]        = df_agre["franja_ts"].dt.day
df_agre["dia_semana"] = df_agre["franja_ts"].dt.dayofweek + 1
df_agre["franja"]     = df_agre["franja_ts"].dt.time

df_cal = (
    df[["fecha_inicio", "fecha_fin", "tipo_estacionalidad", "nombre_evento"]]
    .drop_duplicates()
    .reset_index(drop=True)
)

prioridad = {
    "DIAS_CORRIENTES":    0,
    "TEMPORADA_NACIONAL": 1,
    "FESTIVO_NACIONAL":   2,
    "FIESTA_ATLANTICO":   3,
}
df_cal["_prio"] = df_cal["tipo_estacionalidad"].map(prioridad).fillna(0)
df_cal = df_cal.sort_values("_prio", ascending=False).reset_index(drop=True)

filas = []
for _, row in df_cal.iterrows():
    for d in pd.date_range(row["fecha_inicio"], row["fecha_fin"], freq="D"):
        filas.append({
            "fecha":               d.date(),
            "tipo_estacionalidad": row["tipo_estacionalidad"],
            "nombre_evento":       row["nombre_evento"],
        })

df_calendario = (
    pd.DataFrame(filas)
      .drop_duplicates(subset=["fecha"])
      .reset_index(drop=True)
)

df_agre["fecha"] = df_agre["franja_ts"].dt.date
df_agre = df_agre.merge(df_calendario, on="fecha", how="left")

df_agre = df_agre.set_index("franja_ts").sort_index()

df_agre = df_agre[
    ["franja", "anio", "mes", "dia", "dia_semana",
     "tipo_estacionalidad", "nombre_evento",
     "pasajeros", "n_viajes"]
]

El número de viajes despachados y el número de viajes cancelados por franja se excluyen del conjunto de features del modelo porque son resultados operativos conocidos únicamente después del cierre de la franja.

In [170]:
_ = toolkit.dataframe_integrity_blocks(df_agre, n_blocks=2)

Variable,Data type,Variable,Data type
franja,time,tipo_estacionalidad,str
anio,int32,nombre_evento,str
mes,int32,pasajeros,int32
dia,int32,n_viajes,int16
dia_semana,int32,,


La forma de agregación adoptada garantiza tres propiedades sobre el dataset resultante: (i) no existen franjas huérfanas dentro de la ventana operativa, ya que cada uno de los 1.096 días contiene exactamente las 65 franjas de 15 minutos entre 04:30 y 20:30; (ii) no existen días sin ningún despacho, salvo un único caso identificado; y (iii) no existen valores nulos en ninguna columna. El reindex sobre ventana operativa, en lugar del reindex sobre el día calendario completo, elimina los ceros estructurales (madrugada y noche sin servicio) y deja como únicos ceros aquellos que representan ausencia real de demanda dentro de la operación.

El único día completamente en cero es el 2024-09-06. Su presencia en el dataset no se asume como error: la verificación cruzada con fuentes externas confirmó que ese día hubo bloqueos masivos en Barranquilla, con suspensión de operaciones de Transmetro y adhesión de SOBUSA al cese de actividades. El día se conserva como un cero real, no como falla de captura, porque la distinción es metodológicamente relevante: el día existió operativamente, el servicio no se prestó, y esa ausencia es información válida para el motor de alertas operativas. Los días de menor demanda del período registran entre 4.000 y 7.500 pasajeros, muy por encima del cero, lo que confirma que el 2024-09-06 no es un feriado de baja demanda sino una jornada con suspensión efectiva de operaciones.

Se contrastó la demanda derivada de progvehiculos (`df_agre`) con los consolidados por patrón de `timbradas_anio_k54` sobre 4.121 patrones con ratio calculable. La mediana del ratio `subidas_agre` / `subidas_timb` es 1.09, con rango intercuartílico (0.70, 1.65), lo que indica consistencia agregada entre ambas fuentes: en el patrón típico, la demanda consolidada coincide con la demanda derivada del registro operativo.

El diagrama de dispersión del ratio frente al número de días que componen cada patrón revela una estructura fuertemente discreta: los puntos se agrupan en bandas verticales nítidas en torno a 1, 3, 11–13, 37–44 y 50–56 días, correspondientes a festivos únicos, bloques de Semana Santa, puentes y patrones recurrentes de días corrientes. Dentro de cada banda la dispersión es amplia, especialmente en los patrones de baja frecuencia (n = 1), donde el ratio varía en varios órdenes de magnitud. La correlación de Spearman ($\rho$ = 0.013) y la tau de Kendall ($\tau$ = 0.008) son prácticamente nulas, lo que descarta cualquier asociación sistemática entre la frecuencia del patrón y el ratio.

In [154]:
_, _, _, _ = toolkit.plot_ratio_vs_frequency(
    df_agre, df,
    title="Ratio de abordajes: operativo / anual",
    xlab="Días que componen el patrón",
    ylab="Ratio de abordajes (log)"
)

La conclusión operativa es que `timbradas_anio_k54` es válida como referencia agregada, dado que la mediana del ratio se sitúa próxima a 1 y las correlaciones de frecuencia son prácticamente nulas, pero no como fuente primaria del target. El modelo requiere la resolución por fecha específica que solo `progvehiculos` proporciona, y la dispersión a nivel de patrón individual impide utilizar `timbradas_anio` como ground truth por franja. La estructura discreta del diagrama confirma además que los patrones no son continuos sino eventos agrupados por el calendario operativo. La tabla se utiliza únicamente para el mapeo calendario–estacionalidad (`tipo_estacionalidad`, `nombre_evento`, `fecha_inicio`, `fecha_fin`).

## Caracterización de la demanda

Sobre el conjunto agregado `df_agre` se realiza la caracterización de la demanda. El análisis parte de la serie temporal diaria de pasajeros, examina su distribución por franja, y descompone sus patrones de estacionalidad intradía, semanal y anual. El objetivo es identificar qué dimensiones temporales modulan la demanda de forma significativa, y por tanto merecen representación explícita en el modelo, y cuáles no aportan señal predictiva.

El conjunto de datos se dividió en dos subconjuntos mediante una partición cronológica 80/20. El subconjunto de entrenamiento contiene las primeras 56,992 franjas del período, abarcando desde el 1 de enero de 2023 hasta el 25 de mayo de 2025. El subconjunto de prueba (denominado *holdout set*) contiene las 14,248 franjas restantes, desde el 26 de mayo hasta el 31 de diciembre de 2025.

:::{admonition} Nota: Partición temporal
:class: note
La partición respetó el orden cronológico de los registros. No se aplicó barajado aleatorio. El conjunto de prueba funciona como *holdout set* y permanece intacto para evaluar el desempeño fuera de muestra. Esta estrategia evita la fuga de información entre los conjuntos.
:::

Aunque algunos de los modelos empleados en este proyecto no incorporan un componente recurrente en su arquitectura, respetar la estructura temporal es indispensable. Los *lags* y las ventanas móviles que alimentan al modelo se construyen con `shift()` sobre el índice temporal; una partición aleatoria arrastraría valores futuros hacia el entrenamiento y produciría métricas artificialmente optimistas. El objetivo del sistema es anticipar demanda futura, no describir la pasada, por lo que la evaluación debe reflejar la capacidad real de generalización hacia adelante.

In [171]:
train, test, fecha_corte = toolkit.split_and_save(df_agre)

Saved:
  ..\data\processed\train.parquet    — 56,992 time slots
  ..\data\processed\holdout.parquet  — 14,248 time slots

Cutoff date: 2025-05-26 17:30:00
Train: 2023-01-01 04:30:00 → 2025-05-26 17:15:00
Test:  2025-05-26 17:30:00 → 2025-12-31 20:30:00

Train share:   80.0 %
Holdout share: 20.0 %


La serie diaria agregada por suma expone la estructura general de la demanda en el período. Se distinguen interrupciones puntuales, reconocibles como caídas abruptas hacia valores cercanos a cero en días aislados, cuyo patrón sugiere la incidencia de eventos externos sobre la operación (por ejemplo, septiembre de 2024). Se insinúa además una modulación de escala mayor, con ascensos hacia el final de la primera mitad del año y descensos al cierre del año, y se observan posibles reducciones en la demanda entre un año y el siguiente.

A nivel de franja, la demanda sigue un perfil bimodal dentro de cada jornada: un primer pico en la mañana, un valle al mediodía y un segundo pico al final de la tarde. Ese perfil se modula por un ciclo semanal marcado, visible como la alternancia entre días laborales de alta actividad y fines de semana de menor demanda. La forma del perfil intradía se mantiene entre semanas de distintos meses, lo que sugiere que el patrón es estructural y no depende de la estación. Un evento como el paro de septiembre de 2024 irrumpe de forma abrupta en la serie, pero el patrón de los días adyacentes se mantiene: una vez concluido el evento, la demanda retoma el nivel y la forma previos.

In [172]:
_, _ = toolkit.plot_temporal_panel(
    train, zoom_left=("2023-03-06", "2023-03-12"),
    zoom_right=("2024-09-02", "2024-09-08"),
    text_left="marzo 2023", text_right="septiembre 2024",
    title="Demanda de pasajeros (2023-2025)",
    xlab_zoom="Día del mes", ylab_daily="Pasajeros por día",
    ylab_zoom="Pasajeros por franja", hspace=0.05
)

La ACF sobre la serie por franja, calculada con 500 rezagos, muestra una oscilación sostenida con picos regulares que se repiten cada 32-33 rezagos. Ese intervalo corresponde a media jornada operativa, dado que el día se compone de 65 franjas de 15 minutos entre 04:30 y 20:30. La presencia de estos picos semi-diurnos refleja la forma bimodal del perfil intradía: los picos de la mañana y de la tarde generan alta correlación entre franjas separadas por medio día. Los picos también aparecen en los múltiplos exactos de 65 (65, 130, 195, ...), correspondientes a días operativos completos. La amplitud de los picos no es constante: crece y decrece formando un sobre que se refuerza alrededor del rezago 455, equivalente a 7 $\times$ 65, es decir, una semana operativa completa. La periodicidad observada es consistente con la presencia de un ciclo semanal estable superpuesto a las estructuras semi-diurna y diaria que caracterizan la serie.

La PACF cae abruptamente tras el primer rezago, señal de que la dependencia directa de corto plazo se concentra en la franja inmediatamente anterior. Sin embargo, no se mantiene totalmente plana: aparecen picos pequeños pero sistemáticos en los múltiplos de 65, que indican que la estructura diaria no queda completamente capturada por el retardo inmediato. La combinación de una ACF con oscilación persistente y una PACF dominada por el primer rezago pero con residuos en la escala diaria es característica de series con fuerte componente estacional sobre una memoria de corto plazo dominante.

In [165]:
_, _ = toolkit.plot_acf_pacf(
    train["pasajeros"],
    lags=500, figsize=(12, 4),
    titles=("Autocorrelación (ACF)", "Autocorrelación parcial (PACF)"),
    xlab="Rezago", ylab="Autocorrelación",
)

La serie diferenciada mediante `diff(65)` remueve la dependencia de cada franja respecto al mismo slot del día anterior. El resultado expone la estructura que en la serie original quedaba enmascarada por el ciclo diario. La ACF cae en los primeros rezagos, atraviesa una zona negativa entre los rezagos 100 y 400, y muestra un rebote positivo en torno al rezago 455. Ese rebote evidencia que la estacionalidad semanal persiste después de eliminar el ciclo diario: si ambos ciclos no fueran independientes, la ACF diferenciada se mantendría plana en esa zona. El rezago 455 equivale a 7 × 65, es decir, una semana operativa completa, lo que confirma que la periodicidad del rebote coincide con el ciclo semanal.

:::{admonition} Nota: Diferenciación
:class: note

La diferenciación de una serie temporal $X_t$ produce una nueva serie que corresponde a la diferencia entre cada observación y su valor en un rezago anterior. Formalmente:

$$
\Delta_k X_t = X_t - X_{t-k}
$$

donde $k$ es el orden del rezago. Esta operación elimina la dependencia dominante respecto al rezago $k$ y expone componentes que quedan ocultos bajo esa dependencia. En series de conteo, como la de pasajeros, la diferenciación simple es la transformación adecuada.

En este caso, la serie de pasajeros por franja se diferencia con $k = 65$, el número de franjas que componen una jornada operativa. La transformación remueve el ciclo diario y deja visible la estructura semanal y de mayor escala que subyace a la serie original.
:::

La PACF sobre la serie diferenciada presenta picos en los múltiplos de 65 (65, 130, 195, 260, 325, 390, 455), más visibles que en la serie original. Esa mejora indica que la correlación parcial a escala diaria estaba siendo absorbida por la autocorrelación de corto plazo, y que al removerla emerge como estructura sistemática.

In [166]:
_, _ = toolkit.plot_acf_pacf(
    train["pasajeros"].diff(65).dropna(),
    lags=500, figsize=(12, 4),
    titles=("Autocorrelación (ACF)", "Autocorrelación parcial (PACF)"),
    xlab="Rezago", ylab="Autocorrelación",
)

La distribución de pasajeros por franja se caracteriza por una forma asimétrica con cola hacia la derecha: la mayor parte de las franjas se concentra en valores bajos y medios, y la frecuencia decae de forma sostenida hacia valores altos, sin una segunda moda ni saltos abruptos. Esa morfología indica que la demanda se distribuye de manera continua dentro de la operación, con predominio de franjas de baja y media ocupación. Se observa además una proporción apreciable de franjas sin pasajeros reportados. Esas franjas responden a distintas causas: intervalos en los que no se registró ningún despacho, franjas donde hubo despacho pero la demanda estuvo limitada por eventos externos (como el paro de septiembre de 2024), y franjas de borde de jornada donde la operación es naturalmente de baja actividad.

:::{admonition} Nota: Demanda diaria y Agregación
:class: note

Sea $x_f$ el total de pasajeros de la franja $f$. El total diario $x_d$ se obtiene sumando las franjas operativas del día $d$:

$$
x_d = \sum_{f \in \text{franjas}(d)} x_f
$$

Para niveles de agregación superiores (semanal, mensual, anual), el valor representativo del período se calcula como la mediana de los totales diarios que lo componen:

$$
\tilde{x}_T = \text{mediana}\left(\{x_d : d \in T\}\right)
$$

donde $T$ es el período considerado.
:::

La demanda diaria muestra diferencias entre años, pero las diferencias no son marcadas y el orden no es monótono. El año 2023 registra el nivel más alto, mientras que los primeros meses de 2025 (enero a mayo) superan ligeramente el promedio diario de 2024. Esta comparación está sesgada por la composición temporal de cada conjunto: 2025 cubre únicamente los primeros cinco meses del año, que coinciden con la primera cresta del patrón anual bimodal (enero-junio). Con estos valores no es posible afirmar la existencia de un drift decreciente sostenido ni de un patrón anual definido.

In [167]:
_, _, _ = toolkit.plot_distribution_and_yearly_demand(
    train, titles=("Distribución de pasajeros por franja",
            "Demanda diaria por año"),
    xlab_hist="Pasajeros por franja", ylab_hist="Frecuencia relativa",
    xlab_bar="Año", ylab_bar="Pasajeros por día"
)

La distribución de ceros por franja horaria se concentra en los extremos de la jornada operativa. Las franjas de apertura (04:30 y 04:45) y de cierre (20:15 y 20:30) acumulan la mayor parte de los casos, con más de 170 y 200 franjas respectivamente. En el resto del día los ceros son residuales. La mayoría corresponden a franjas sin ningún viaje registrado, y una fracción menor a franjas con viajes efectivos pero sin pasajeros.

In [173]:
_, _, tabla = toolkit.plot_zeros_by_time_slot(
    train, xlab="Franja horaria",
    ylab="Franjas con cero pasajeros",
    title="Composición de ceros por franja",
    type_labels=("Sin despacho", "Cero con viajes")
)

Este patrón responde al efecto de discretización en bloques de 15 minutos. Los primeros despachos y los últimos no siempre caen dentro de la franja teórica de apertura o cierre, por lo que algunas franjas quedan sin ningún viaje registrado aunque la ruta sí esté operando. La consecuencia práctica es que los ceros de borde no representan ausencia de demanda sino un desfase entre el horario efectivo de operación y la ventana de agregación. Los ceros del centro de la jornada, en cambio, son escasos y corresponden mayoritariamente a franjas sin despacho registrado.

La demanda agregada por mes, combinando los tres años mediante la mediana de los totales diarios, sugiere un perfil bimodal dentro del año. La primera cresta se extiende de febrero a mayo, con máximo en febrero. Un descenso aparece en junio y julio. La segunda cresta se desarrolla de agosto a noviembre, con máximo en agosto, y la serie desciende hacia diciembre. La primera cresta es ligeramente superior a la segunda. La evidencia es compatible con un patrón anual de dos fases, aunque la magnitud de la diferencia entre crestas y valle no permite afirmarlo con certeza.

In [177]:
_, _, _ = toolkit.plot_demand_by_month(
    train, xlab="Mes", ylab="Pasajeros por día",
    title="Demanda diaria por mes y año",
    month_labels=("Ene", "Feb", "Mar", "Abr", "May", "Jun",
                  "Jul", "Ago", "Sep", "Oct", "Nov", "Dic")
)

La comparación mes a mes entre años revela un orden consistente que el análisis agregado por año no permitía observar. Al enfrentar el mismo mes en distintos años, la comparación neutraliza el sesgo que introduce la composición temporal de cada conjunto y aísla el efecto del año. La reducción de la demanda entre años es sistemática y no depende de la fase del ciclo anual.

A diferencia del análisis por meses, la agregación por semana del mes no muestra un patrón intra-mensual definido. Los valores agregados de las cuatro semanas son similares entre sí, y la posición de la semana dentro del mes no modula la demanda de forma visible. La semana del mes no es, por tanto, una dimensión donde la estructura temporal de la demanda se exprese de forma clara.

In [178]:
_, _, _ = toolkit.plot_demand_by_week_of_month(
    train, xlab="Semana del mes", ylab="Pasajeros por día",
    title="Demanda diaria por semana del mes y año",
    week_labels=("Semana 1", "Semana 2", "Semana 3", "Semana 4"),
    ylim_top_factor=1.5
)

La demanda por día de la semana reproduce el patrón ya sugerido por la serie diaria y la ACF. Los días laborales (lunes a viernes) concentran la mayor demanda y se mantienen en un rango estrecho entre sí, sin una estructura interna clara dentro del bloque laboral. El sábado marca una caída intermedia, y el domingo registra el nivel más bajo de la semana, con un valor cercano a la mitad del promedio laboral. La separación entre el bloque lunes-viernes y el fin de semana es marcada, y consistente en los tres años. El orden entre años se mantiene en todos los días, con 2023 como el año de mayor demanda.

In [179]:
_, _, _ = toolkit.plot_demand_by_weekday(
    train, xlab="Día de la semana", ylab="Pasajeros por día",
    title="Demanda diaria por día de la semana y año",
    weekday_labels=("Lun", "Mar", "Mié", "Jue", "Vie", "Sáb", "Dom")
)

El perfil intradía conserva una forma bimodal común a los tres años: pico en la mañana (05:30), valle extendido alrededor del mediodía (10:30–11:30), segundo pico en la tarde (13:30–14:30) y descenso progresivo hacia el cierre. La forma es estable, pero la amplitud relativa varía. La diferencia entre 2023 y los años posteriores no se distribuye uniformemente a lo largo del día: en las horas de la mañana las tres series se superponen, mientras que a partir de las 14:00 la serie de 2023 se separa hacia arriba y mantiene la brecha hasta el cierre. La reducción de la demanda entre años se concentra, por tanto, en las horas de la tarde. Esto sugiere que el efecto del año no es aditivo y depende de la franja horaria.

In [180]:
_, _, _ = toolkit.plot_demand_by_time_slot(
    train, xlab="Franja horaria", ylab="Pasajeros (mediana)", 
    title="Demanda por franja horaria y año"
)

La demanda diaria no es homogénea entre tipos de día. Los días corrientes concentran el nivel más alto y funcionan como base de la operación. Los días de Fiesta Atlántico se mantienen cercanos a ese nivel, lo que sugiere que eventos como el Carnaval no reducen la operación sino que la sostienen en valores relativamente altos. La Temporada Nacional y el Festivo Nacional sí reducen la demanda, con magnitudes distintas: la temporada cae a un nivel intermedio, y el festivo es el que produce la mayor reducción. Los tipos de día especiales, por tanto, no actúan como un bloque uniforme: cada uno modula la demanda de forma distinta, y el efecto no es intercambiable entre categorías.

In [181]:
_, _, tabla = toolkit.plot_demand_by_seasonality(
    df_agre, xlab="Tipo de estacionalidad",
    ylab="Pasajeros por día",
    title="Demanda diaria por tipo de estacionalidad y año",
    category_labels=("Días corrientes", "Fiesta del Atlántico",
                     "Temporada nacional", "Festivo nacional"),
)

## Conclusiones e implicaciones

El análisis exploratorio deja tres conclusiones que condicionan el diseño del modelo.

La primera es que la demanda tiene estructura multi-escala. Los picos semi-diurnos en la ACF (cada 32-33 rezagos) y los diarios (cada 65) confirman el perfil bimodal dentro de cada jornada. El ciclo semanal, visible en el rebote de la ACF diferenciada en el rezago 455, se superpone a la estructura intradía. La implicación directa es que los lags del modelo deben construirse a esas escalas: `shift(1)` y `shift(4)` para memoria inmediata y horaria, `shift(32)` y `shift(33)` para el ciclo semi-diurno, `shift(65)` para el mismo slot del día anterior, y `shift(455)` para el mismo slot de la semana anterior. La estructura cíclica anual se refuerza con variables de hora, día de semana y mes codificadas con seno y coseno, para que el modelo capture la periodicidad sin depender de valores enteros consecutivos.

La segunda es que el tipo de estacionalidad no actúa como un bloque uniforme. Los días corrientes y las fiestas de atlántico sostienen la demanda en niveles altos, mientras que la Temporada Nacional y los Festivos Nacionales la reducen con magnitudes distintas. Como la categoría es nominal y tiene pocos valores, la codificación adecuada es one-hot o una codificación ordinal explícita basada en el nivel observado.

La tercera, y la más importante para interpretar correctamente el modelo, es que la demanda registrada no equivale a la demanda potencial. Una franja con pasajeros igual a cero puede corresponder a un intervalo sin despacho, a un día de paro, o a una jornada con operación reducida. En todos esos casos la ausencia de pasajeros refleja una restricción operativa, no una ausencia de demanda en la ruta. Lo mismo aplica a los niveles bajos: que un día registre menos pasajeros no significa que menos personas quisieran viajar, sino que la ruta transportó menos. Esta distinción es crítica para el motor de alertas y para la interpretación de las recomendaciones del optimizador. Una predicción baja no debe leerse como "no vale la pena despachar", sino como "el sistema capturó menos actividad", y la causa debe explorarse antes de ajustar la frecuencia.

La demografía de la ruta, la demanda latente de la zona de influencia, y las condiciones de accesibilidad del corredor son independientes de la actividad registrada. El objetivo del modelo será pronosticar la demanda efectivamente capturada por la ruta bajo las condiciones operativas vigentes, y no la demanda latente del corredor.